In [2]:
import numpy as np
import pandas as pd
import matplotlib.pyplot as plt
from scipy.optimize import curve_fit
import plotly.graph_objects as go

In [3]:
df = pd.read_csv("stability_surface_box_N2000_grid200.csv")
print(df.head())
print(df.columns)
print(df.shape)

     a    b         c    x         y     z
0  1.0  0.3  0.300000  0.3  0.300000  18.0
1  1.0  0.3  0.303491  0.3  0.303491  19.0
2  1.0  0.3  0.307023  0.3  0.307023  19.0
3  1.0  0.3  0.310597  0.3  0.310597  20.0
4  1.0  0.3  0.314211  0.3  0.314211  20.0
Index(['a', 'b', 'c', 'x', 'y', 'z'], dtype='str')
(40000, 6)


## Visualize our raw data

In [4]:
# Rohdaten Scatterplot
fig1 = go.Figure(data=[go.Scatter3d(
    x=df['c'],
    y=df['b'],
    z=df['z'],
    mode='markers',
    marker=dict(size=1.5, color=df['z'], colorscale='Viridis', opacity=0.6)
)])

fig1.update_layout(
    title="complete raw data",
    scene=dict(xaxis_type="log", yaxis_type="log", zaxis_title="Stabilität z"),
    width=900, height=700
)
fig1.show()


## Filter interior of the volcanic crater and outer wings

In [5]:
import numpy as np
import pandas as pd
import plotly.graph_objects as go

# --------------------------------------------------
# 1. Daten laden
# --------------------------------------------------
df = pd.read_csv("stability_surface_box_N2000_grid200.csv")
df = df.sort_values(["b", "c"]).reset_index(drop=True)

# --------------------------------------------------
# 2. Log-Koordinaten u, v und z
# --------------------------------------------------
u = (np.log(df["b"].values) + np.log(df["c"].values)) / np.sqrt(2)
v = (np.log(df["b"].values) - np.log(df["c"].values)) / np.sqrt(2)
z = df["z"].values

df["u"] = u
df["v"] = v

# --------------------------------------------------
# 3. Zonen definieren
# --------------------------------------------------
center_zone = np.abs(v) < 0.35
outer_zone = np.abs(v) > 1.0

# --------------------------------------------------
# 4. Harte Schwellen
# --------------------------------------------------
z_center = z[center_zone]
thr_low_center = np.percentile(z_center, 12) if len(z_center) > 0 else z.min()

z_high_outer = 50

print("thr_low_center =", thr_low_center)
print("z_high_outer   =", z_high_outer)

# --------------------------------------------------
# 5. Maske bauen
# --------------------------------------------------
mask = np.ones(len(z), dtype=bool)

# Zentrum: tiefe Lochpunkte entfernen
mask &= ~(center_zone & (z < thr_low_center))

# Außen: hohe Punkte entfernen
mask &= ~(outer_zone & (z > z_high_outer))

# --------------------------------------------------
# 5b. Breitere Corner-foot rescue
# --------------------------------------------------
corner_foot_zone = (
    ((df["b"].values > 1.6) & (df["c"].values > 1.6)) |
    ((df["b"].values < 0.65) & (df["c"].values < 0.65))
)

z_corner_max = 80
mask |= (corner_foot_zone & (z <= z_corner_max))

df["keep"] = mask

print("Kept points:", mask.sum(), "of", len(mask))

# --------------------------------------------------
# 6. 3D-Plot in Plotly
# --------------------------------------------------
df_keep = df[df["keep"]].copy()
df_drop = df[~df["keep"]].copy()

fig = go.Figure()

# entfernte Punkte
fig.add_trace(go.Scatter3d(
    x=df_drop["c"],
    y=df_drop["b"],
    z=df_drop["z"],
    mode="markers",
    marker=dict(
        size=1.4,
        color="lightgray",
        opacity=0.12
    ),
    name="excluded"
))

# behaltene Punkte
fig.add_trace(go.Scatter3d(
    x=df_keep["c"],
    y=df_keep["b"],
    z=df_keep["z"],
    mode="markers",
    marker=dict(
        size=2.0,
        color=df_keep["z"],
        colorscale="Hot",
        opacity=0.94,
        colorbar=dict(title="z")
    ),
    name="kept"
))

fig.update_layout(
    title="Stability landscape without high outer wing points",
    scene=dict(
        xaxis=dict(
            title="c/a",
            type="log",
            tickmode="array",
            tickvals=[0.1, 0.2, 0.5, 1, 2, 5, 10],
            ticktext=["0.1", "0.2", "0.5", "1", "2", "5", "10"],
            showgrid=True
        ),
        yaxis=dict(
            title="b/a",
            type="log",
            tickmode="array",
            tickvals=[0.1, 0.2, 0.5, 1, 2, 5, 10],
            ticktext=["0.1", "0.2", "0.5", "1", "2", "5", "10"],
            showgrid=True
        ),
        zaxis=dict(
            title="z"
        )
    ),
    width=980,
    height=760
)

fig.show()

thr_low_center = 43.0
z_high_outer   = 50
Kept points: 37773 of 40000


In [6]:
import numpy as np
from scipy.optimize import curve_fit
from sklearn.metrics import r2_score, mean_squared_error, mean_absolute_error
import plotly.graph_objects as go

# --------------------------------------------------
# 1. Wir nehmen EXAKT dein df_keep (kein neues Filtern!)
# --------------------------------------------------
u_data = df_keep["u"].values
v_data = df_keep["v"].values
z_data = df_keep["z"].values

# --------------------------------------------------
# 2. Das Rationale Modell (Egg-Shape)
# --------------------------------------------------
def volcano_rational_model(X, u0, a0, kappa, b0, C, f0):
    u_val, v_val = X
    # Deine Geometrie
    denom = a0 * (1.0 + kappa * (u_val - u0))
    # Numerischer Schutz
    denom = np.where(np.abs(denom) < 0.01, 0.01 * np.sign(denom), denom)
    phi = ((u_val - u0)**2) / (denom**2) + (v_val**2) / (b0**2)
    
    return f0 + C / (1.0 + phi)

# --------------------------------------------------
# 3. Fit ausführen
# --------------------------------------------------
# Startwerte basierend auf deinen Daten
p0 = [0.239, 0.927, -0.339, 0.601, 120.0, z_data.min()]

params, _ = curve_fit(
    volcano_rational_model, (u_data, v_data), z_data, 
    p0=p0, maxfev=100000
)

# Metriken
z_pred = volcano_rational_model((u_data, v_data), *params)
r2 = r2_score(z_data, z_pred)
rmse = np.sqrt(mean_squared_error(z_data, z_pred))
mae = mean_absolute_error(z_data, z_pred)

# --------------------------------------------------
# 4. Ausgabe & Visualisierung
# --------------------------------------------------

# Die berechneten Parameter
param_names = ["u0 (Zentrum u)", "a0 (Breite u)", "kappa (Asymmetrie)", "b0 (Breite v)", "C (Amplitude)", "f0 (Boden)"]
print("--- Gefittete Modellparameter ---")
for name, val in zip(param_names, params):
    print(f"{name:20}: {val:.4f}")

# Statistiken
print(f"\nStatistiken:")
print(f"R²   : {r2:.4f}")
print(f"RMSE : {rmse:.4f}")
print(f"MAE  : {mae:.4f}")

# Fläche für den Plot erzeugen (basierend auf den Grenzen deiner df_keep)
b_range = np.geomspace(df_keep["b"].min(), df_keep["b"].max(), 100)
c_range = np.geomspace(df_keep["c"].min(), df_keep["c"].max(), 100)
B_grid, C_grid = np.meshgrid(b_range, c_range, indexing='ij')

U_grid = (np.log(B_grid) + np.log(C_grid)) / np.sqrt(2)
V_grid = (np.log(B_grid) - np.log(C_grid)) / np.sqrt(2)
Z_grid = volcano_rational_model((U_grid, V_grid), *params)

fig = go.Figure()
# Punkte
fig.add_trace(go.Scatter3d(x=df_keep["c"], y=df_keep["b"], z=df_keep["z"], 
                            mode='markers', marker=dict(size=2, color=df_keep["z"], colorscale='Hot', opacity=0.8)))
# Fit-Fläche
fig.add_trace(go.Surface(x=c_range, y=b_range, z=Z_grid, colorscale='Viridis', opacity=0.7))

fig.update_layout(scene=dict(xaxis_type="log", yaxis_type="log"), title="Finaler Fit auf bereinigten Daten", width=1000, height=800)
fig.show()

--- Gefittete Modellparameter ---
u0 (Zentrum u)      : 0.0324
a0 (Breite u)       : 0.8011
kappa (Asymmetrie)  : -0.0616
b0 (Breite v)       : 0.4658
C (Amplitude)       : 205.6581
f0 (Boden)          : -11.5537

Statistiken:
R²   : 0.9864
RMSE : 4.8297
MAE  : 3.8359


In [9]:
import numpy as np
import pandas as pd
from scipy.optimize import curve_fit, differential_evolution
from sklearn.metrics import r2_score, mean_squared_error
import plotly.graph_objects as go
from plotly.subplots import make_subplots

# 1. Modell-Definition (wie gehabt)
def volcano_model(X, u0, a0, kappa, b0, C, f0):
    u, v = X
    denom_u = a0 * (1.0 + kappa * (u - u0))
    denom_u = np.where(np.abs(denom_u) < 1e-6, 1e-6 * np.sign(denom_u), denom_u)
    phi = ((u - u0)**2) / (denom_u**2) + (v**2) / (b0**2)
    return f0 + C / (1.0 + phi)

# 2. Daten laden & Filtern (df_keep ist deine bereinigte Basis)
u_data = df_keep["u"].values
v_data = df_keep["v"].values
z_data = df_keep["z"].values

# 3. Finaler High-Precision Fit
bounds = [(0.0, 0.5), (0.1, 2.0), (-0.8, 0.0), (0.1, 1.5), (50, 300), (0, 20)]
p0 = [0.03, 0.7, -0.05, 0.4, 200, 0]

params, _ = curve_fit(volcano_model, (u_data, v_data), z_data, p0=p0, 
                       bounds=([b[0] for b in bounds], [b[1] for b in bounds]))

# 4. Berechnung der Residuen (Fehler pro Punkt)
z_pred = volcano_model((u_data, v_data), *params)
residuals = z_data - z_pred

# 5. Visualisierung: Fit vs. Fehler
fig = make_subplots(
    rows=1, cols=2,
    specs=[[{'type': 'surface'}, {'type': 'scatter3d'}]],
    subplot_titles=(f"Finaler Fit (R²: {r2_score(z_data, z_pred):.4f})", "Residuen (Wo liegen die Fehler?)")
)

# Plot 1: Die glatte Modellfläche
c_range = np.geomspace(df_keep["c"].min(), df_keep["c"].max(), 70)
b_range = np.geomspace(df_keep["b"].min(), df_keep["b"].max(), 70)
B_mesh, C_mesh = np.meshgrid(b_range, c_range)
U_mesh = (np.log(B_mesh) + np.log(C_mesh)) / np.sqrt(2)
V_mesh = (np.log(B_mesh) - np.log(C_mesh)) / np.sqrt(2)
Z_mesh = volcano_model((U_mesh, V_mesh), *params)

fig.add_trace(go.Surface(x=c_range, y=b_range, z=Z_mesh, colorscale='Viridis', opacity=0.8, showscale=False), row=1, col=1)

# Plot 2: Fehler-Map (Rot = Modell zu niedrig, Blau = Modell zu hoch)
fig.add_trace(go.Scatter3d(
    x=df_keep["c"], y=df_keep["b"], z=residuals,
    mode='markers', marker=dict(size=2, color=residuals, colorscale='RdBu', cmid=0, opacity=0.6),
    name="Residuen"
), row=1, col=2)

fig.update_layout(width=1200, height=600, scene1=dict(xaxis_type="log", yaxis_type="log"),
                  scene2=dict(xaxis_type="log", yaxis_type="log", zaxis_title="Abweichung"))
fig.show()